In [559]:
import pandas as pd
import geopandas as gpd
import matplotlib.pyplot as plt
from matplotlib.colors import LinearSegmentedColormap, Normalize
import folium
import os
import yaml
import io
from PIL import Image
import selenium
import warnings
import xml.etree.ElementTree as ET
from typing import Union

In [2]:
os.getcwd()

'/Users/nictam/Documents/Coding Projects/Chinese Demographics Analysis'

In [495]:
warnings.filterwarnings("ignore")

## Parameters

In [577]:
CENSUS_YEARS = ["2001", "2006", "2011", "2016", "2021"]
SINOPHONE_PCT_THRESHOLD = 0.1
SINOPHONE_POP_THRESHOLD = 500
CMA_CODE = "535" # 933 = YVR; 535 = YYZ

In [451]:
ns_uri = 'http://www.SDMX.org/resources/SDMXML/schemas/v2_0/generic'
NS = f'{{{ns_uri}}}' # Namespace

In [486]:
def get_parameters(year: str) -> Union[str, str, str, str, dict]:
    #DIM_NAME = "DIM0" if year != "2011" else "MTNDr"
    xml_path = os.path.join(os.getcwd(), "Datasets", year + " CT.xml") # CENSUS XML
    csv_path = os.path.join(os.getcwd(), "Datasets", year + " CT.csv") # CENSUS CSV
    yaml_path = os.path.join(os.getcwd(), "Datasets", "Reference Lines.yaml") # REFERENCE LINE YAML
    shp_path = os.path.join(os.getcwd(), "Shapefiles", year, "Boundary.shp")

    with open(yaml_path, 'r') as file:
        reference_fields = yaml.safe_load(file)
        target_dim_dict = reference_fields["Census" + year]

    return xml_path, csv_path, shp_path, target_dim_dict

## Reading Data File

In [247]:
with open(YAML_PATH, 'r') as file:
    reference_fields = yaml.safe_load(file)
    TARGET_DIM_DICT = reference_fields["Census" + YEAR]

In [248]:
TARGET_DIM_DICT

{'1': 'Population',
 '690': 'Cantonese',
 '686': 'Mandarin',
 '685': 'Hakka',
 '687': 'MinDong',
 '688': 'MinNan',
 '689': 'Wu',
 '692': 'NIE',
 '691': 'NOS',
 '1374': 'Knowledge_Cantonese',
 '1370': 'Knowledge_Mandarin'}

In [589]:
# FOR 2001, 2006, 2011 FILES:
def extract_xml(year: str, xml_path: str, target_dim_dict: dict) -> pd.DataFrame:
    records = []
    for event, elem in ET.iterparse(xml_path, events=("end",)):
        if elem.tag == f"{NS}Series":   # USE Series AS THE PARENT
            key = elem.find(f"{NS}SeriesKey")
            # INITIATE VARIABLES
            geo = None
            dim0 = None
            for val in key: # GET ALL CHILDREN UNDER SeriesKey
                concept = val.attrib.get("concept") # GET THE CHILD NAME "Concept"
                if concept == "GEO":
                    geo = val.attrib.get("value") # IF THE concept IS "GEO", GET THE RESPECTIVE "value"
                elif concept == "DIM0" or concept == "MTNDr": # "MTNDr" IS USED IN 2011 INSTEAD OF DIM0
                    dim0 = val.attrib.get("value")
                elif concept == "Sex": # ONLY IN 2011
                    sex = val.attrib.get("value")

            if year != "2011":
                sex = "1" # SET VALUE TO "1" (TOTAL) FOR OTHER YEARS

            # DECIDE WHICH VALUES TO KEEP
            if geo is not None and geo.startswith(CMA_CODE) and len(geo) > 3 and dim0 in target_dim_dict.keys() and sex == "1":
                obs = elem.find(f"{NS}Obs").find(f"{NS}ObsValue")

                if obs is not None:
                    obsvalue = obs.attrib.get("value")
                    records.append({
                        "GEO": geo,
                        "DIM0": target_dim_dict[dim0],
                        "ObsValue": obsvalue,
                    })

            elem.clear()  # FREE MEMORY

    return pd.DataFrame(records)

In [254]:
df = pd.read_csv(CSV_PATH, encoding = "latin-1")
df.head()

/var/folders/p6/zglr11td2m78vvhmv6hj4l8c0000gn/T/ipykernel_63526/1751094880.py:1: DtypeWarning: Columns (4) have mixed types. Specify dtype option on import or set low_memory=False.
  df = pd.read_csv(CSV_PATH, encoding = "latin-1")


,CENSUS_YEAR,DGUID,ALT_GEO_CODE,GEO_LEVEL,GEO_NAME,TNR_SF,TNR_LF,DATA_QUALITY_FLAG,CHARACTERISTIC_ID,CHARACTERISTIC_NAME,...,C2_COUNT_MEN+,SYMBOL.1,C3_COUNT_WOMEN+,SYMBOL.2,C10_RATE_TOTAL,SYMBOL.3,C11_RATE_MEN+,SYMBOL.4,C12_RATE_WOMEN+,SYMBOL.5
0,2021,2021S0503932,932.0,Census metropolitan area,Abbotsford - Mission,2.7,3.7,0,1,"Population, 2021",...,NaN,...,NaN,...,NaN,...,NaN,...,NaN,...
1,2021,2021S0503932,932.0,Census metropolitan area,Abbotsford - Mission,2.7,3.7,0,2,"Population, 2016",...,NaN,...,NaN,...,NaN,...,NaN,...,NaN,...
2,2021,2021S0503932,932.0,Census metropolitan area,Abbotsford - Mission,2.7,3.7,0,3,"Population percentage change, 2016 to 2021",...,NaN,...,NaN,...,8.4,NaN,NaN,...,NaN,...
3,2021,2021S0503932,932.0,Census metropolitan area,Abbotsford - Mission,2.7,3.7,0,4,Total private dwellings,...,NaN,...,NaN,...,NaN,...,NaN,...,NaN,...
4,2021,2021S0503932,932.0,Census metropolitan area,Abbotsford - Mission,2.7,3.7,0,5,Private dwellings occupied by usual residents,...,NaN,...,NaN,...,NaN,...,NaN,...,NaN,...


In [612]:
def extract_csv(year: str, csv_path: str, target_dim_dict: dict) -> pd.DataFrame:
    df = pd.read_csv(csv_path, encoding = "latin-1", dtype = {'ALT_GEO_CODE': str})

    # RENAME AND DROP UNNEEDED COLUMNS 
    if year == "2016":
        # FILTER FOR YVR
        df = df[df['GEO_LEVEL'] == 2]
        df = df[df['ALT_GEO_CODE'].astype(str).str.startswith(CMA_CODE)]
        df.columns = ['YEAR', 'GEO_CODE', 'GEO_LEVEL', 'GEO_NAME', 'GNR', 'GNR_LF', 'DATA_QUALITY_FLAG', 'ALT_GEO_CODE',
                      'LINE_TITLE', 'LINE_ID', 'LINE_NOTES', 'VALUE', 'VALUE_M', 'VALUE_F']
    elif year == "2021":
        df = df[df['GEO_LEVEL'] == "Census tract"]
        df = df[df['ALT_GEO_CODE'].astype(str).str.startswith(CMA_CODE)]  
        df['ALT_GEO_CODE'] = df['ALT_GEO_CODE'].astype(str).apply(lambda x: x[:7] + x[8:])
        df = df.rename(columns = {'CHARACTERISTIC_ID': 'LINE_ID', 'C1_COUNT_TOTAL': 'VALUE'})
        
    df = df[['ALT_GEO_CODE', 'LINE_ID', 'VALUE']]

    # MAP LINE_ID WITH THEIR DEFINITIONS
    df['LINE_ID'] = df['LINE_ID'].astype(str)
    df = df[df['LINE_ID'].isin(target_dim_dict.keys())]
    df['DIM0'] = df['LINE_ID'].map(target_dim_dict)

    # RE-ORDER COLUMNS TO MATCH XML OUTPUTS
    df = df[['ALT_GEO_CODE', 'DIM0', 'VALUE']]
    df.columns = ['GEO', 'DIM0', 'ObsValue']

    return df

In [193]:
df = extract_xml()
print(df.head())
print(f"\nMatched {len(df)} records")

FileNotFoundError: [Errno 2] No such file or directory: '/Users/nictam/Documents/Coding Projects/Chinese Demographics Analysis/Datasets/2016 CT.xml'

In [403]:
df = extract_csv()
print(df.head())
print(f"\nMatched {len(df)} records")

/var/folders/p6/zglr11td2m78vvhmv6hj4l8c0000gn/T/ipykernel_63526/2768010708.py:2: DtypeWarning: Columns (4) have mixed types. Specify dtype option on import or set low_memory=False.
  df = pd.read_csv(CSV_PATH, encoding = "latin-1", dtype = {'ALT_GEO_CODE': str})


                GEO        DIM0  ObsValue
14157411  933000101  Population    6154.0
14158095  933000101       Hakka       0.0
14158096  933000101    Mandarin     185.0
14158097  933000101     MinDong       0.0
14158098  933000101      MinNan      35.0

Matched 5885 records


## Data Cleaning

In [408]:
pivoted_df = df.pivot(index = "GEO", columns = "DIM0", values = "ObsValue")
pivoted_df = pivoted_df.apply(pd.to_numeric, errors = "coerce")
pivoted_df

DIM0,Cantonese,Hakka,Knowledge_Cantonese,Knowledge_Mandarin,Mandarin,MinDong,MinNan,NIE,NOS,Population,Wu
GEO,,,,,,,,,,,
933000101,730.0,0.0,835.0,400.0,185.0,0.0,35.0,0.0,10.0,6154.0,10.0
933000102,1520.0,10.0,1990.0,1180.0,535.0,5.0,35.0,0.0,10.0,8245.0,15.0
933000201,1280.0,10.0,1340.0,655.0,260.0,0.0,35.0,0.0,5.0,6949.0,10.0
933000203,1315.0,5.0,1485.0,560.0,200.0,0.0,15.0,0.0,0.0,3908.0,10.0
933000204,730.0,20.0,995.0,360.0,130.0,0.0,15.0,0.0,0.0,4527.0,5.0
...,...,...,...,...,...,...,...,...,...,...,...
933050501,15.0,0.0,0.0,15.0,10.0,0.0,5.0,0.0,0.0,3530.0,0.0
933050503,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,96.0,0.0
933050504,35.0,0.0,25.0,100.0,130.0,0.0,10.0,0.0,0.0,6228.0,0.0


In [410]:
pivoted_df = pivoted_df.fillna(0)

In [411]:
language_columns = [column for column in pivoted_df.columns if column not in ('GEO', 'Population', "NOS", "Knowledge_Cantonese", "Knowledge_Mandarin")]

In [412]:
pivoted_df['majority_lang'] = pivoted_df[language_columns].idxmax(axis = 1)
pivoted_df['majority_lang'] = pivoted_df['majority_lang'].apply(lambda x: x if x in ("Cantonese", "Mandarin") else "Others")
pivoted_df['majority_pop'] = pivoted_df[language_columns].max(axis = 1)

In [413]:
pivoted_df['chinese_lang_pop'] = pivoted_df[language_columns].sum(axis = 1)
pivoted_df['majority_percent'] = pivoted_df['majority_pop'] / pivoted_df['chinese_lang_pop']


In [414]:
# MASK VALUES IF COMMUNITY HAS LESS THAN 500 PEOPLE OR LESS THAN 10 % CHINESE LANGUAGE SPEAKERS
pivoted_df['chinese_lang_pct'] = pivoted_df['chinese_lang_pop'] / pivoted_df['Population']

In [455]:
pivoted_df['majority_lang'] = pivoted_df['majority_lang'].mask((pivoted_df['chinese_lang_pct'] < SINOPHONE_PCT_THRESHOLD) | (pivoted_df['Population'] < SINOPHONE_POP_THRESHOLD))
pivoted_df['majority_pop'] = pivoted_df['majority_pop'].mask((pivoted_df['chinese_lang_pct'] < SINOPHONE_PCT_THRESHOLD) | (pivoted_df['Population'] < SINOPHONE_POP_THRESHOLD))

In [416]:
pivoted_df

DIM0,Cantonese,Hakka,Knowledge_Cantonese,Knowledge_Mandarin,Mandarin,MinDong,MinNan,NIE,NOS,Population,Wu,majority_lang,majority_pop,chinese_lang_pop,majority_percent,chinese_lang_pct
GEO,,,,,,,,,,,,,,,,
933000101,730.0,0.0,835.0,400.0,185.0,0.0,35.0,0.0,10.0,6154.0,10.0,Cantonese,730.0,960.0,0.760417,0.155996
933000102,1520.0,10.0,1990.0,1180.0,535.0,5.0,35.0,0.0,10.0,8245.0,15.0,Cantonese,1520.0,2120.0,0.716981,0.257126
933000201,1280.0,10.0,1340.0,655.0,260.0,0.0,35.0,0.0,5.0,6949.0,10.0,Cantonese,1280.0,1595.0,0.802508,0.229529
933000203,1315.0,5.0,1485.0,560.0,200.0,0.0,15.0,0.0,0.0,3908.0,10.0,Cantonese,1315.0,1545.0,0.851133,0.395343
933000204,730.0,20.0,995.0,360.0,130.0,0.0,15.0,0.0,0.0,4527.0,5.0,Cantonese,730.0,900.0,0.811111,0.198807
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
933050501,15.0,0.0,0.0,15.0,10.0,0.0,5.0,0.0,0.0,3530.0,0.0,NaN,NaN,30.0,0.500000,0.008499
933050503,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,96.0,0.0,NaN,NaN,0.0,NaN,0.000000
933050504,35.0,0.0,25.0,100.0,130.0,0.0,10.0,0.0,0.0,6228.0,0.0,NaN,NaN,175.0,0.742857,0.028099


In [549]:
def data_cleaning(df: pd.DataFrame) -> pd.DataFrame:
    pivoted_df = df.pivot(index = "GEO", columns = "DIM0", values = "ObsValue")
    pivoted_df = pivoted_df.apply(pd.to_numeric, errors = "coerce")
    pivoted_df = pivoted_df.fillna(0)

    # LISTING ALL LANGUAGES THAT ARE IN SCOPE
    language_columns = [column for column in pivoted_df.columns if column not in ('GEO', 'Population', "NOS", "Knowledge_Cantonese", "Knowledge_Mandarin")]

    pivoted_df['majority_lang'] = pivoted_df[language_columns].idxmax(axis = 1)
    pivoted_df['majority_lang'] = pivoted_df['majority_lang'].apply(lambda x: x if x in ("Cantonese", "Mandarin") else "Others")
    pivoted_df['majority_pop'] = pivoted_df[language_columns].max(axis = 1)

    pivoted_df['chinese_lang_pop'] = pivoted_df[language_columns].sum(axis = 1)
    pivoted_df['majority_percent'] = pivoted_df['majority_pop'] / pivoted_df['chinese_lang_pop']

    # MASK VALUES IF COMMUNITY HAS LESS THAN 500 PEOPLE OR LESS THAN 10 % CHINESE LANGUAGE SPEAKERS
    pivoted_df['chinese_lang_pct'] = pivoted_df['chinese_lang_pop'] / pivoted_df['Population']
    pivoted_df['majority_lang'] = pivoted_df['majority_lang'].mask((pivoted_df['chinese_lang_pct'] < SINOPHONE_PCT_THRESHOLD) | (pivoted_df['chinese_lang_pop'] < SINOPHONE_POP_THRESHOLD))
    pivoted_df['majority_pop'] = pivoted_df['majority_pop'].mask((pivoted_df['chinese_lang_pct'] < SINOPHONE_PCT_THRESHOLD) | (pivoted_df['chinese_lang_pop'] < SINOPHONE_POP_THRESHOLD))
    
    return pivoted_df

## Shapefile

In [419]:
sr_shapefile = gpd.read_file(SHP_PATH)

In [420]:
sr_shapefile

,CTUID,DGUID,CTNAME,LANDAREA,PRUID,geometry
0,5370001.08,2021S05075370001.08,0001.08,1.6383,35,"POLYGON ((7196507.366 869787.991, 7196501.617 ..."
1,0010002.00,2021S05070010002.00,0002.00,1.9638,10,"POLYGON ((8980216.643 2151065.36, 8980377.609 ..."
2,5370001.09,2021S05075370001.09,0001.09,1.9699,35,"POLYGON ((7196437.003 869160.246, 7196434.403 ..."
3,5370120.02,2021S05075370120.02,0120.02,76.9650,35,"POLYGON ((7189475.703 865662.849, 7189448.943 ..."
4,0010006.00,2021S05070010006.00,0006.00,1.0467,10,"POLYGON ((8980091.143 2152478.609, 8980100.254..."
...,...,...,...,...,...,...
6242,5591003.00,2021S05075591003.00,1003.00,227.6981,35,"POLYGON ((6984736.931 712991.68, 6984866.56 71..."
6243,5591004.00,2021S05075591004.00,1004.00,18.3792,35,"POLYGON ((6981553.974 701146.583, 6981728.169 ..."
6244,5800300.00,2021S05075800300.00,0300.00,314.4614,35,"POLYGON ((7084392.943 1223795.154, 7084451.317..."
6245,6020800.00,2021S05076020800.00,0800.00,8.6987,46,"POLYGON ((5828241.16 1509841.949, 5828231.78 1..."


In [421]:
# FILTER FOR VANCOUVER CMA
if 'CMAUID' in sr_shapefile.columns:
    yvr_shapefile = sr_shapefile[sr_shapefile['CMAUID'] == "933"]
else:
    yvr_shapefile = sr_shapefile[sr_shapefile['CTUID'].astype(str).str.startswith('933')]

In [422]:
# DROP THE DECIMAL TO MATCH THE KEYS
yvr_shapefile['CTUID'] = yvr_shapefile['CTUID'].apply(lambda x: x[:7] + x[8:])

/Users/nictam/miniconda/lib/python3.10/site-packages/geopandas/geodataframe.py:1968: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  super().__setitem__(key, value)


In [423]:
# KEEP ONLY THE NEEDED COLUMNS
yvr_shapefile = yvr_shapefile[['CTUID', 'geometry']]

In [424]:
yvr_shapefile = yvr_shapefile.to_crs(epsg=4326)

In [320]:
#yvr_shapefile['CTUID'] = yvr_shapefile['CTUID'].astype(int)

In [425]:
yvr_shapefile

,CTUID,geometry
164,933018711,"POLYGON ((-122.75614 49.14906, -122.75612 49.1..."
557,933040004,"POLYGON ((-122.49873 49.22034, -122.49343 49.2..."
564,933010103,"POLYGON ((-123.07318 49.31289, -123.07402 49.3..."
572,933010104,"POLYGON ((-123.06928 49.31893, -123.06931 49.3..."
578,933001401,"POLYGON ((-123.05936 49.22044, -123.05936 49.2..."
...,...,...
6127,933028723,"POLYGON ((-122.75786 49.3514, -122.73408 49.35..."
6133,933040103,"POLYGON ((-122.57924 49.20395, -122.57942 49.2..."
6134,933040104,"POLYGON ((-122.58092 49.20332, -122.58069 49.2..."
6135,933029008,"POLYGON ((-122.77533 49.25908, -122.77532 49.2..."


In [426]:
map_df = pivoted_df.merge(yvr_shapefile, how = "left", left_index = True, right_on = "CTUID")

In [427]:
map_df

,Cantonese,Hakka,Knowledge_Cantonese,Knowledge_Mandarin,Mandarin,MinDong,MinNan,NIE,NOS,Population,Wu,majority_lang,majority_pop,chinese_lang_pop,majority_percent,chinese_lang_pct,CTUID,geometry
4291,730.0,0.0,835.0,400.0,185.0,0.0,35.0,0.0,10.0,6154.0,10.0,Cantonese,730.0,960.0,0.760417,0.155996,933000101,"POLYGON ((-123.02367 49.21204, -123.02371 49.2..."
4292,1520.0,10.0,1990.0,1180.0,535.0,5.0,35.0,0.0,10.0,8245.0,15.0,Cantonese,1520.0,2120.0,0.716981,0.257126,933000102,"POLYGON ((-123.02768 49.21005, -123.02807 49.2..."
4276,1280.0,10.0,1340.0,655.0,260.0,0.0,35.0,0.0,5.0,6949.0,10.0,Cantonese,1280.0,1595.0,0.802508,0.229529,933000201,"POLYGON ((-123.04137 49.2183, -123.04138 49.21..."
2149,1315.0,5.0,1485.0,560.0,200.0,0.0,15.0,0.0,0.0,3908.0,10.0,Cantonese,1315.0,1545.0,0.851133,0.395343,933000203,"POLYGON ((-123.05938 49.21195, -123.05917 49.2..."
2150,730.0,20.0,995.0,360.0,130.0,0.0,15.0,0.0,0.0,4527.0,5.0,Cantonese,730.0,900.0,0.811111,0.198807,933000204,"POLYGON ((-123.0597 49.21147, -123.05917 49.21..."
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
4099,15.0,0.0,0.0,15.0,10.0,0.0,5.0,0.0,0.0,3530.0,0.0,NaN,NaN,30.0,0.500000,0.008499,933050501,"POLYGON ((-122.59661 49.17476, -122.59534 49.1..."
3803,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,96.0,0.0,NaN,NaN,0.0,NaN,0.000000,933050503,"POLYGON ((-122.56952 49.17974, -122.56945 49.1..."
3804,35.0,0.0,25.0,100.0,130.0,0.0,10.0,0.0,0.0,6228.0,0.0,NaN,NaN,175.0,0.742857,0.028099,933050504,"POLYGON ((-122.58472 49.19128, -122.58251 49.1..."
4280,15.0,0.0,0.0,35.0,15.0,0.0,0.0,0.0,0.0,4255.0,0.0,NaN,NaN,30.0,0.500000,0.007051,933050601,"POLYGON ((-122.47225 49.06048, -122.4707 49.06..."


In [564]:
unary_union = map_df['geometry'].geometry.unary_union.centroid
print(unary_union.x, unary_union.y)

-122.83604993263644 49.28271436437622


In [566]:
map_df.total_bounds

array([-123.43193384,   49.00191908, -122.4086399 ,   49.57427534])

In [398]:
print(map_df['majority_pop'].isna())

4291.0    False
4292.0    False
4276.0    False
2149.0    False
2150.0    False
          ...  
4099.0     True
3803.0     True
3804.0     True
4280.0     True
4281.0     True
Name: majority_pop, Length: 535, dtype: bool


In [399]:
map_df['CTUID'].value_counts()

CTUID
933000101    1
933018912    1
93302010     1
933020002    1
933020001    1
            ..
933014003    1
933014002    1
93301350     1
93301340     1
933050602    1
Name: count, Length: 535, dtype: int64

In [428]:
map_df = map_df.set_geometry("geometry")

In [429]:
# DROPPING BLANK ROWS
map_mask = (map_df['majority_percent'].isna()) & (~map_df['majority_lang'].isna())

In [430]:
map_df = map_df[~map_mask]

In [485]:
def get_shapefile(shp_path: str) -> gpd.GeoDataFrame:
    sr_shapefile = gpd.read_file(shp_path)
    
    # FILTER FOR VANCOUVER CMA
    if 'CMAUID' in sr_shapefile.columns:
        cma_shapefile = sr_shapefile[sr_shapefile['CMAUID'] == CMA_CODE]
    else:
        cma_shapefile = sr_shapefile[sr_shapefile['CTUID'].astype(str).str.startswith(CMA_CODE)]

    # DROP THE DECIMAL TO MATCH THE KEYS
    cma_shapefile['CTUID'] = cma_shapefile['CTUID'].apply(lambda x: x[:7] + x[8:])

    # KEEP ONLY THE NEEDED COLUMNS
    cma_shapefile = cma_shapefile[['CTUID', 'geometry']]

    cma_shapefile = cma_shapefile.to_crs(epsg=4326)

    return cma_shapefile
    

In [460]:
def consolidate_df(data_df: pd.DataFrame, shape_df: gpd.GeoDataFrame) -> gpd.GeoDataFrame:
    map_df = data_df.merge(shape_df, how = "left", left_index = True, right_on = "CTUID")

    # DROPPING BLANK ROWS
    map_mask = (map_df['majority_percent'].isna()) & (~map_df['majority_lang'].isna())
    map_df = map_df[~map_mask]

    map_df = map_df.set_geometry("geometry")

    return map_df

## Plotting

In [431]:
cmaps = {
    "Cantonese": LinearSegmentedColormap.from_list("canto", ["#A8C5E8", "#0A3D7A"]),
    "Mandarin": LinearSegmentedColormap.from_list("mando", ["#F4C2C2", "#8B0000"]),
    "Others": LinearSegmentedColormap.from_list("others", ["#E9B071", "#844B18"])
}

norm = Normalize(vmin = 0.38, vmax = 0.72, clip = True)

In [432]:
norm = Normalize(vmin = 0.38, vmax = 0.72, clip = True)

In [433]:
def get_colour(row):
    cmap = cmaps.get(row['properties']["majority_lang"])

    if row['properties']["majority_lang"] is None:
        return "#DDDDDD"
    if cmap is None:
        return "#DDDDDD"  # FOR REGIONS WITH LESS THAN 5 % SINOPHONES

    share = row['properties']['majority_percent']
    r, g, b, a = cmap(norm(share))
    return f"#{int(r*255):02x}{int(g*255):02x}{int(b*255):02x}"
    #return cmap(norm(row['properties']["majority_percent"]))

In [545]:
def style_function(feature):
    
    return {
        "fillColor": get_colour(feature),
        "color": "black",       
        "weight": 0.28,
        "fillOpacity": 0.82,
    }

In [607]:
def gen_map(map_df: gpd.GeoDataFrame) -> folium.Map:

    def get_colour(row):
        cmap = cmaps.get(row['properties']["majority_lang"])
    
        if row['properties']["majority_lang"] is None:
            return "#DDDDDD"
        if cmap is None:
            return "#DDDDDD"  # FOR REGIONS WITH LESS THAN 5 % SINOPHONES
    
        share = row['properties']['majority_percent']
        r, g, b, a = cmap(norm(share))
        return f"#{int(r*255):02x}{int(g*255):02x}{int(b*255):02x}"

    def style_function(feature):
        return {
            "fillColor": get_colour(feature),
            "color": "black",       
            "weight": 0.28,
            "fillOpacity": 0.82,
        }

    cmaps = {
    "Cantonese": LinearSegmentedColormap.from_list("canto", ["#A8C5E8", "#0A3D7A"]),
    "Mandarin": LinearSegmentedColormap.from_list("mando", ["#F4C2C2", "#8B0000"]),
    "Others": LinearSegmentedColormap.from_list("others", ["#E9B071", "#844B18"])
    }

    norm = Normalize(vmin = 0.38, vmax = 0.72, clip = True)

    clean_map = map_df[map_df.geometry.notna() & ~map_df.geometry.is_empty & map_df.geometry.is_valid]


    #m = folium.Map(location=[49.2, -122.9], zoom_start=10, tiles="Stadia.StamenTonerLite")
    m = folium.Map(location = [clean_map['geometry'].geometry.unary_union.centroid.y,
                              clean_map['geometry'].geometry.unary_union.centroid.x],
                   zoom_start = 10, tiles="Stadia.StamenTonerLite")
    folium.GeoJson(
    map_df,
    style_function=style_function,
    tooltip=folium.GeoJsonTooltip(
        fields=["majority_lang", "majority_percent"],
        aliases=["Language:", "Percentage (%):"],
    ),
    ).add_to(m)

    return m

In [573]:
def get_bounds(map_df: pd.DataFrame) -> list:
    total_bounds = map_df.total_bounds
    return [[total_bounds[1] - 0.05, total_bounds[0] - 0.05], [total_bounds[3] + 0.05, total_bounds[2] + 0.05]]

In [570]:
get_bounds()

[[np.float64(48.9519190833542), np.float64(-123.48193384050698)],
 [np.float64(49.62427534050434), np.float64(-122.35863989919658)]]

In [546]:
m = folium.Map(location=[49.2, -122.9], zoom_start=10, tiles="Stadia.StamenTonerLite")
folium.GeoJson(
    map_df,
    style_function=style_function,
    tooltip=folium.GeoJsonTooltip(
        fields=["majority_lang", "majority_percent"],
        aliases=["Language:", "Percentage (%):"],
    ),
).add_to(m)

In [547]:
m

##### 2001

In [109]:
m

##### 2006

In [136]:
m

##### 2011

In [170]:
m

The history saving thread hit an unexpected error (OperationalError('attempt to write a readonly database')).History will not be written to the database.


##### 2016

In [235]:
m

##### 2021

In [436]:
m

In [446]:
img_data = m._to_png()
img = Image.open(io.BytesIO(img_data))
img.save(os.path.join(os.getcwd(), 'image.png'))

In [447]:
m.save(os.path.join(os.getcwd(), "map.html"))

# Main Program

In [613]:
def gen_map_seq() -> list:
    map_list = []
    for year in CENSUS_YEARS:
        print(year)
        xml_path, csv_path, shp_path, target_dim_dict = get_parameters(year)

        if year in ["2001", "2006", "2011"]:
            df = extract_xml(year, xml_path, target_dim_dict)
        else:
            df = extract_csv(year, csv_path, target_dim_dict)

        df = data_cleaning(df)
        
        shape_df = get_shapefile(shp_path)
        map_df = consolidate_df(df, shape_df)

        #if year == "2001": # The first iteration
        #    bounds = get_bounds(map_df)
        
        m = gen_map(map_df)

        map_list.append(m)

    return map_list

In [630]:
year = "2021"
xml_path, csv_path, shp_path, target_dim_dict = get_parameters(year)
df = extract_csv(year, csv_path, target_dim_dict)
df = data_cleaning(df)
shape_df = get_shapefile(shp_path)
map_df = consolidate_df(df, shape_df)

In [551]:
map_list = gen_map_seq()

2001
2006
2011
2016
2021


In [558]:
map_list[0]

In [554]:
map_list[1]

In [555]:
map_list[2]

In [556]:
map_list[3]

In [557]:
map_list[4]

#### Toronto (535)

In [614]:
map_list = gen_map_seq()

2001
2006
2011
2016
2021


In [628]:
map_list[0]

In [624]:
map_list[1]

In [625]:
map_list[2]

In [626]:
map_list[3]

In [627]:
map_list[4]

In [631]:
map_df

,Cantonese,Hakka,Knowledge_Cantonese,Knowledge_Mandarin,Mandarin,MinDong,MinNan,NIE,NOS,Population,Wu,majority_lang,majority_pop,chinese_lang_pop,majority_percent,chinese_lang_pct,CTUID,geometry
904,25.0,0.0,25.0,10.0,15.0,0.0,0.0,0.0,0.0,599.0,0.0,NaN,NaN,40.0,0.625000,0.066778,535000100,"MULTIPOLYGON (((-79.342 43.61947, -79.34203 43..."
905,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,604.0,0.0,NaN,NaN,0.0,NaN,0.000000,535000200,"MULTIPOLYGON (((-79.38428 43.61915, -79.38429 ..."
906,10.0,0.0,0.0,15.0,15.0,0.0,5.0,0.0,0.0,457.0,0.0,NaN,NaN,30.0,0.500000,0.065646,535000300,"MULTIPOLYGON (((-79.44282 43.63378, -79.44284 ..."
907,25.0,0.0,60.0,45.0,25.0,0.0,0.0,0.0,0.0,6306.0,0.0,NaN,NaN,50.0,0.500000,0.007929,535000400,"POLYGON ((-79.43603 43.63717, -79.43549 43.635..."
908,95.0,0.0,160.0,115.0,60.0,0.0,20.0,0.0,5.0,6957.0,5.0,NaN,NaN,180.0,0.527778,0.025873,535000500,"POLYGON ((-79.42365 43.64088, -79.42318 43.640..."
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
2783,40.0,5.0,30.0,130.0,80.0,0.0,0.0,0.0,0.0,4088.0,0.0,NaN,NaN,125.0,0.640000,0.030577,535082007,"POLYGON ((-79.05782 43.85975, -79.05628 43.856..."
4032,50.0,5.0,80.0,120.0,80.0,0.0,0.0,0.0,5.0,4964.0,0.0,NaN,NaN,135.0,0.592593,0.027196,535083000,"POLYGON ((-79.12972 44.06907, -79.12957 44.068..."
5431,10.0,0.0,0.0,0.0,15.0,0.0,0.0,0.0,0.0,5660.0,0.0,NaN,NaN,25.0,0.600000,0.004417,535083101,"POLYGON ((-79.14361 44.10432, -79.14501 44.104..."
5432,15.0,0.0,10.0,25.0,10.0,0.0,0.0,0.0,0.0,6904.0,0.0,NaN,NaN,25.0,0.600000,0.003621,535083102,"POLYGON ((-79.07983 44.08004, -79.08076 44.079..."


In [632]:
map_df[map_df['CTUID'] == '535042106']

,Cantonese,Hakka,Knowledge_Cantonese,Knowledge_Mandarin,Mandarin,MinDong,MinNan,NIE,NOS,Population,Wu,majority_lang,majority_pop,chinese_lang_pop,majority_percent,chinese_lang_pct,CTUID,geometry
5456,255.0,5.0,330.0,340.0,215.0,0.0,10.0,0.0,5.0,4294.0,0.0,NaN,NaN,485.0,0.525773,0.112948,535042106,"POLYGON ((-79.43609 43.86621, -79.43589 43.865..."
